# Live Flanagan microworld generation and querying

This notebook sends a generic pouring action to a real language model, constrains the response with the selected Flanagan schema, validates the resulting description-level graph, and makes the admitted `HypothesisRecord` queryable.

The input is an **action type**, not an observed episode. The result therefore describes stereotypical knowledge about cereal pouring: phases, roles, events, predictions, control points, errors, corrections, parameters, and internal-model structure. It does not bind those roles to particular objects in the current world.

Before running the notebook, export one provider key in the shell that starts Jupyter:

```bash
export OPENAI_API_KEY=your-key
# or: export ANTHROPIC_API_KEY=your-key
```

The key is read from the environment and is never printed or stored in notebook output. The generation cell makes a paid external request. A single generation may make additional repair requests if the first graph violates the microworld constraints.

In [1]:
from __future__ import annotations

import json
import os
from dataclasses import dataclass
from enum import StrEnum
from dotenv import load_dotenv
load_dotenv(override=True)

from IPython.display import JSON, display

from llm_reasoner.clients.anthropic_client import AnthropicClient
from llm_reasoner.clients.base import LanguageModelClient
from llm_reasoner.clients.openai_client import OpenAIClient
from llm_reasoner.knowledge.generation import (
    CachingGenerator,
    HypothesisGenerator,
    derive_schema,
)
from llm_reasoner.knowledge.hypothesis import InMemoryStore, encode
from llm_reasoner.knowledge.microworlds.flanagan.constraints import SUITE
from llm_reasoner.knowledge.microworlds.flanagan.core import (
    ActionPhase,
    CorrectiveAction,
    ModelUpdate,
    PredictionComparison,
    PredictionError,
    SensorimotorControlPoint,
)
from llm_reasoner.knowledge.microworlds.flanagan.pouring import (
    FlowRegulationPhase,
)
from llm_reasoner.knowledge.microworlds.registry import (
    Capability,
    SOMA,
    select_modules,
    task_reference,
)
from llm_reasoner.knowledge.query import Cited, HypothesisView


In [2]:
os.getenv('OPENAI_API_KEY')

'sk-REDACTED-API-KEY'

## 1. Choose the provider and generation policy

Change only `provider` to switch services. The default models mirror the package clients. `force_generation=False` means rerunning the generation cell reuses the in-memory result; set it to `True` only when you intentionally want another paid sample. `additional_capabilities` is the extension point for optional Flanagan modules.

In [3]:
class Provider(StrEnum):
    """Identify a supported live language-model service."""

    OPENAI = "openai"
    ANTHROPIC = "anthropic"


class ApiKeyEnvironmentVariable(StrEnum):
    """Name the environment variable owned by each provider."""

    OPENAI = "OPENAI_API_KEY"
    ANTHROPIC = "ANTHROPIC_API_KEY"


@dataclass(frozen=True)
class LiveGenerationConfiguration:
    """Configure one reproducible notebook generation workflow."""

    provider: Provider = Provider.OPENAI
    """Service used for the live structured completion."""

    openai_model: str = "gpt-4o-mini"
    """OpenAI model selected when :attr:`provider` is OpenAI."""

    anthropic_model: str = "claude-haiku-4-5"
    """Anthropic model selected when :attr:`provider` is Anthropic."""

    maximum_repairs: int = 2
    """Additional completions allowed after constraint violations."""

    force_generation: bool = False
    """Whether to bypass a valid result already held by the notebook store."""

    additional_capabilities: frozenset[Capability] = frozenset()
    """Optional Flanagan capability modules added to the pouring profile."""


@dataclass
class MissingApiKey(RuntimeError):
    """Report that the selected provider has no available credential."""

    environment_variable: ApiKeyEnvironmentVariable
    """Environment variable that must contain the provider credential."""

    def __str__(self) -> str:
        """Return setup guidance without exposing credential content."""
        return f"Set {self.environment_variable.value} before running the pipeline cell."


@dataclass
class HypothesisNotServable(RuntimeError):
    """Report a generated graph rejected by the acceptance constraints."""

    errors: tuple[str, ...]
    """Constraint errors that prevented admission."""

    def __str__(self) -> str:
        """Return all rejection reasons as one diagnostic."""
        return "Generated hypothesis was rejected:\n" + "\n".join(self.errors)


configuration = LiveGenerationConfiguration()
configuration


LiveGenerationConfiguration(provider=<Provider.OPENAI: 'openai'>, openai_model='gpt-5.6-sol', anthropic_model='claude-haiku-4-5', maximum_repairs=2, force_generation=False, additional_capabilities=frozenset())

## 2. Declare the description-level input

The trigger input has two parts:

1. a typed task reference whose ancestry lets the registry select the pouring profile;
2. a plain-language action label that gives the model the intended generic activity.

No particular cereal box, bowl, pose, measurement, or robot instance is supplied. Those belong to later world-state resolution, not hypothesis generation.

In [4]:
task = task_reference(
    iri=SOMA + "PouringInto",
    ancestors=(
        SOMA + "Pouring",
        SOMA + "Actuating",
        SOMA + "PhysicalTask",
    ),
    label="Pouring into a receptacle",
)
action_label = "pour cereal from a cereal box into a bowl"
display(task)
display(action_label)


ConceptReference(iri='http://www.ease-crc.org/ont/SOMA.owl#PouringInto', label='Pouring into a receptacle', ancestors=frozenset({'http://www.ease-crc.org/ont/SOMA.owl#Pouring', 'http://www.ease-crc.org/ont/SOMA.owl#Actuating', 'http://www.ease-crc.org/ont/SOMA.owl#PhysicalTask'}))

'pour cereal from a cereal box into a bowl'

## 3. Inspect module selection

Selection is deterministic and does not call the model. For this task, the pouring profile pulls in phase structuring, object dynamics, prehension, and substance-transfer vocabulary through capabilities and declared module dependencies.

In [5]:
selection = select_modules(
    task,
    additional_capabilities=configuration.additional_capabilities,
)
display(selection.profile)
display(selection.capabilities)
display(selection.modules)


TaskProfile(task=ConceptReference(iri='http://www.ease-crc.org/ont/SOMA.owl#Pouring', label='Pouring', ancestors=frozenset({'http://www.ease-crc.org/ont/SOMA.owl#Actuating', 'http://www.ease-crc.org/ont/SOMA.owl#PhysicalTask'})), requires=frozenset({<Capability.PREHENSILE_MANIPULATION: 'prehensile_manipulation'>, <Capability.SUBSTANCE_TRANSFER: 'substance_transfer'>, <Capability.PHASE_STRUCTURING: 'phase_structuring'>, <Capability.OBJECT_DYNAMICS: 'object_dynamics'>}), root_class=<GenerationRoot.POURING_PHASE_STRUCTURE: 'PouringPhaseStructure'>, is_fallback=False)

frozenset({<Capability.OBJECT_DYNAMICS: 'object_dynamics'>,
           <Capability.PHASE_STRUCTURING: 'phase_structuring'>,
           <Capability.PREHENSILE_MANIPULATION: 'prehensile_manipulation'>,
           <Capability.SUBSTANCE_TRANSFER: 'substance_transfer'>})

(MicroworldModule(name='llm_reasoner.knowledge.microworlds.flanagan.core', version='1.0.0', provides=frozenset({<Capability.PHASE_STRUCTURING: 'phase_structuring'>}), depends_on=frozenset(), mandatory=True, note='Action-neutral. Mandatory, so it is loaded even under the fallback profile, which is what lets an unknown action still generate.'),
 MicroworldModule(name='llm_reasoner.knowledge.microworlds.flanagan.object_dynamics', version='1.0.0', provides=frozenset({<Capability.OBJECT_DYNAMICS: 'object_dynamics'>}), depends_on=frozenset({'llm_reasoner.knowledge.microworlds.flanagan.core'}), mandatory=False, note='Action-neutral represented dynamics used by prehensile manipulation.'),
 MicroworldModule(name='llm_reasoner.knowledge.microworlds.flanagan.prehension', version='1.0.0', provides=frozenset({<Capability.PREHENSILE_MANIPULATION: 'prehensile_manipulation'>}), depends_on=frozenset({'llm_reasoner.knowledge.microworlds.flanagan.object_dynamics'}), mandatory=False, note='Action-neutral 

## 4. Inspect the generated output contract

The schema is derived from the same ontological dataclasses used for construction and validation. It is the contract sent to the provider, not a hand-maintained mirror. Inspect `generation_schema.classes` to see every description-level fragment type available to this request.

In [6]:
generation_schema = derive_schema(
    selection.module_names,
    root=selection.root_class,
)
display(generation_schema.root)
display(generation_schema.class_names)


'PouringPhaseStructure'

('ActionPhase',
 'AlignmentErrorEstimate',
 'AlignmentPhase',
 'AnticipatoryGripAdjustment',
 'AuditorySignal',
 'BoundaryControlExemption',
 'CategoricalValue',
 'CenterOfMassShiftEstimate',
 'CohesiveFlowDynamicsEstimate',
 'ConditionRequirement',
 'ContactBreak',
 'ContactEstablishment',
 'ContactEstablishmentPhase',
 'ContactEventType',
 'ContactReleasePhase',
 'ContinuousSignalPrediction',
 'ControlEventType',
 'CorrectiveAction',
 'CorrectiveGripResponse',
 'DesiredState',
 'DynamicViscosityEstimate',
 'DynamicsPerturbation',
 'DynamicsTransfer',
 'EffectorObjectContact',
 'EffectorPositioned',
 'EfferenceCopy',
 'ExpectedCenterOfMassPosition',
 'ExpectedFrictionCoefficient',
 'ExpectedMass',
 'ExpectedShape',
 'ExternalTerminationEventType',
 'FlowCessation',
 'FlowEventType',
 'FlowOnset',
 'FlowOnsetThreshold',
 'FlowRateSetpoint',
 'FlowRegulationPhase',
 'FlowTerminationPhase',
 'ForceDynamicEventType',
 'ForceLoadingPhase',
 'ForcesUnloaded',
 'ForwardModel',
 'GranularFlow

## 5. Build the live client, generator, validator, and cache

This cell reads the selected API key but does not send a request. The generator owns model interaction and repair; the Flanagan constraint suite owns admission; the caching wrapper owns reuse. These remain separate responsibilities.

In [7]:
def api_key_environment_variable(
    provider: Provider,
) -> ApiKeyEnvironmentVariable:
    """Return the credential variable owned by a provider."""
    if provider is Provider.OPENAI:
        return ApiKeyEnvironmentVariable.OPENAI
    return ApiKeyEnvironmentVariable.ANTHROPIC


def create_language_model_client(
    settings: LiveGenerationConfiguration,
) -> LanguageModelClient:
    """Create the selected client from an environment credential."""
    environment_variable = api_key_environment_variable(settings.provider)
    api_key = os.environ.get(environment_variable.value)
    if api_key is None or not api_key.strip():
        raise MissingApiKey(environment_variable)
    if settings.provider is Provider.OPENAI:
        return OpenAIClient(model=settings.openai_model, api_key=api_key)
    return AnthropicClient(model=settings.anthropic_model, api_key=api_key)


language_model_client = create_language_model_client(configuration)
hypothesis_generator = HypothesisGenerator(
    client=language_model_client,
    suite=SUITE,
    max_repairs=configuration.maximum_repairs,
)
hypothesis_store = InMemoryStore()
caching_generator = CachingGenerator(
    generator=hypothesis_generator,
    store=hypothesis_store,
)
display(language_model_client.identity)


'openai:gpt-5.6-sol'

## 6. Trigger real generation

Running the next cell makes the external call. The returned flat fragment graph is decoded into microworld dataclasses, checked by the full Flanagan suite, repaired when necessary, wrapped with provenance, and stored. Only a validated record proceeds to the query cells.

In [8]:
generated_result = caching_generator.get(
    task=task,
    action_label=action_label,
    selection=selection,
    force=configuration.force_generation,
)
record = generated_result.record
if not record.servable:
    raise HypothesisNotServable(record.validation.errors)
view = HypothesisView(record)
display(record.status)


<HypothesisStatus.VALIDATED: 'validated'>

## 7. View the admitted record and its authority

The `record` is the single queryable unit. Its status and validation report say whether it may be served; provenance records the model, prompt version, module versions, repair exchanges, and degradation state; assumptions identify claims that later world-state resolution must check.

In [9]:
display(record.record_id)
display(record.action_type)
display(record.validation)
display(record.provenance)
display(record.assumptions)
display(record.scope.fragments)


'c8d367e637f7'

ConceptReference(iri='http://www.ease-crc.org/ont/SOMA.owl#PouringInto', label='Pouring into a receptacle', ancestors=frozenset({'http://www.ease-crc.org/ont/SOMA.owl#Pouring', 'http://www.ease-crc.org/ont/SOMA.owl#Actuating', 'http://www.ease-crc.org/ont/SOMA.owl#PhysicalTask'}))

ValidationReport(checks_run=113, errors=(), warnings=(), repair_attempts=1)

Provenance(generator='openai:gpt-5.6-sol', prompt_version='generation/v5', module_versions={'llm_reasoner.knowledge.microworlds.flanagan.core': '1.0.0', 'llm_reasoner.knowledge.microworlds.flanagan.object_dynamics': '1.0.0', 'llm_reasoner.knowledge.microworlds.flanagan.prehension': '1.0.0', 'llm_reasoner.knowledge.microworlds.flanagan.pouring': '1.0.0'}, generated_at=datetime.datetime(2026, 9, 29, 12, 1, 14, 78468, tzinfo=datetime.timezone.utc), degraded=False, exchanges=(Exchange(system='You describe what a kind of action involves, in general.\n\nWhat you are producing:\n- A hypothesis about how a kind of manipulation is organised: its phases, what\n  each phase is for, what marks each phase as finished, who or what takes part,\n  and the quantities involved.\n- It is GENERIC. There is no particular scene, no particular object, no\n  particular robot. Never name a specific cup, table or room, and never state a\n  measured value as though you had observed one.\n\nHow to answer:\n- Emit

(Assumption(fragment_id='condition-requirement-2', description='target receptacle remains supported during transfer', on_roles=('role-slot-7', 'role-slot-9')),
 Assumption(fragment_id='condition-requirement', description='source container initially has stable support contact', on_roles=('role-slot-4', 'role-slot-8')))

[PouringPhaseStructure(local_id='pouring-phase-structure', label='generic phase structure for pouring granular cereal from a source container into a target receptacle', decomposes_task=ConceptReference(iri='SOMA:Pouring', label='SOMA:Pouring', ancestors=frozenset()), defines_phase=[ReachPhase(local_id='reach-phase', label='reach toward the cereal-container grasp site', aims_for=Subgoal(local_id='subgoal', label='position the effector for grasp contact', condition_on_role=[RoleSlot(local_id='role-slot-2', label='grasping effector', binds_as=ConceptReference(iri='http://www.ease-crc.org/ont/llm_reasoner/flanagan/prehension#GraspingEffector', label='GraspingEffector', ancestors=frozenset()), min_bindings=1), RoleSlot(local_id='role-slot-3', label='graspable region of the source container', binds_as=ConceptReference(iri='http://www.ease-crc.org/ont/llm_reasoner/flanagan/prehension#GraspSite', label='GraspSite', ancestors=frozenset()), min_bindings=1)], violation_signalled_by=None, attainme

## 8. Query phases, regulation, and boundaries

`HypothesisView` returns cited answers. The citation pairs the record identifier with the local fragment identifier, so downstream decisions can say exactly which generated claim they used.

In [10]:
@dataclass(frozen=True)
class PhaseQueryResult:
    """Collect one phase with its control regime and boundary events."""

    phase: Cited[ActionPhase]
    """Phase answer carrying record and fragment provenance."""

    regulation_mode: object
    """Within-phase feedback mode asserted by the hypothesis."""

    boundaries: tuple[Cited[object], ...]
    """Cited events that terminate the phase."""


phase_results = tuple(
    PhaseQueryResult(
        phase=phase,
        regulation_mode=phase.value.regulation_mode,
        boundaries=tuple(view.boundaries_of(phase)),
    )
    for phase in view.phases()
)
display(phase_results)


(PhaseQueryResult(phase=Cited(value=ReachPhase(local_id='reach-phase', label='reach toward the cereal-container grasp site', aims_for=Subgoal(local_id='subgoal', label='position the effector for grasp contact', condition_on_role=[RoleSlot(local_id='role-slot-2', label='grasping effector', binds_as=ConceptReference(iri='http://www.ease-crc.org/ont/llm_reasoner/flanagan/prehension#GraspingEffector', label='GraspingEffector', ancestors=frozenset()), min_bindings=1), RoleSlot(local_id='role-slot-3', label='graspable region of the source container', binds_as=ConceptReference(iri='http://www.ease-crc.org/ont/llm_reasoner/flanagan/prehension#GraspSite', label='GraspSite', ancestors=frozenset()), min_bindings=1)], violation_signalled_by=None, attainment_signalled_by=ReachTargetReached(local_id='reach-target-reached', label='effector reaches the source-container grasp pose', is_failure_event=False, event_on_role=[RoleSlot(local_id='role-slot-2', label='grasping effector', binds_as=ConceptRefere

## 9. Query predictive control points

Each control point identifies the mechanical event where predictions are evaluated, the expected sensory events, and the available match or mismatch comparisons.

In [11]:
@dataclass(frozen=True)
class ControlPointQueryResult:
    """Collect the predictive-control answers for one boundary."""

    control_point: SensorimotorControlPoint
    """Boundary at which expected and observed consequences are compared."""

    expected_events: tuple[Cited[object], ...]
    """Mechanical events predicted at the boundary."""

    comparisons: tuple[Cited[PredictionComparison], ...]
    """Possible comparison outcomes declared at the boundary."""


control_point_results = tuple(
    ControlPointQueryResult(
        control_point=control_point,
        expected_events=tuple(view.expected_events_at(control_point)),
        comparisons=tuple(view.comparison_at(control_point)),
    )
    for control_point in view.domain(SensorimotorControlPoint)
)
display(control_point_results)


()

## 10. Query errors, corrections, and learning updates

Prediction errors are not terminal labels. They can release typed corrective actions and update represented estimates, making the generated knowledge usable for recovery and adaptation questions.

In [12]:
@dataclass(frozen=True)
class RecoveryQueryResult:
    """Collect motor and representation responses to one error."""

    error: PredictionError
    """Classified mismatch that triggers recovery or adaptation."""

    corrections: tuple[Cited[CorrectiveAction], ...]
    """Cited motor responses released by the error."""

    model_updates: tuple[Cited[ModelUpdate], ...]
    """Cited representation changes supported by the error."""


recovery_results = tuple(
    RecoveryQueryResult(
        error=error,
        corrections=tuple(view.corrections_for(error)),
        model_updates=tuple(view.model_updates_for(error)),
    )
    for error in view.domain(PredictionError)
)
display(recovery_results)


()

## 11. Query by microworld type

`view.domain(SomeClass)` is the general typed query primitive. It includes registered subclasses and returns the actual dataclass instances, so ordinary Python filtering and comparison can refine the result.

In [13]:
flow_regulation_phases = view.domain(FlowRegulationPhase)
prediction_errors = view.domain(PredictionError)
corrective_actions = view.domain(CorrectiveAction)
model_updates = view.domain(ModelUpdate)
display(flow_regulation_phases)
display(prediction_errors)
display(corrective_actions)
display(model_updates)


[FlowRegulationPhase(local_id='flow-regulation-phase', label='regulate granular cereal flow into the target receptacle', aims_for=Subgoal(local_id='subgoal-8', label='regulate cereal flow until the requested quantity is transferred', condition_on_role=[RoleSlot(local_id='role-slot-6', label='granular cereal being transferred', binds_as=ConceptReference(iri='http://www.ease-crc.org/ont/llm_reasoner/flanagan/pouring#PouredSubstance', label='PouredSubstance', ancestors=frozenset()), min_bindings=1), RoleSlot(local_id='role-slot-7', label='target receptacle for the cereal', binds_as=ConceptReference(iri='http://www.ease-crc.org/ont/llm_reasoner/flanagan/pouring#TargetReceptacle', label='TargetReceptacle', ancestors=frozenset()), min_bindings=1)], violation_signalled_by=None, attainment_signalled_by=TargetQuantityReached(local_id='target-quantity-reached', label='requested cereal quantity has entered the target receptacle', is_failure_event=False, event_on_role=[RoleSlot(local_id='role-slot

[]

[]

[]

## 12. View and query the full portable data structure

`encode(record)` produces the complete self-describing flat graph: record metadata, provenance, validation, assumptions, and every fragment with identifier-based references. `encoded_record` is an ordinary Python dictionary, while the `JSON` display below provides a collapsible notebook view. No credential is included.

The raw provider exchanges are retained under provenance for reproducibility and repair diagnostics. Remove that section before sharing the data if the action label itself is sensitive.

In [14]:
encoded_record = encode(record)
display(JSON(data=encoded_record, expanded=False))
print(json.dumps(encoded_record, indent=2))


<IPython.core.display.JSON object>

{
  "format": 1,
  "record_id": "c8d367e637f7",
  "status": "validated",
  "action_type": {
    "iri": "http://www.ease-crc.org/ont/SOMA.owl#PouringInto",
    "label": "Pouring into a receptacle",
    "ancestors": [
      "http://www.ease-crc.org/ont/SOMA.owl#Actuating",
      "http://www.ease-crc.org/ont/SOMA.owl#PhysicalTask",
      "http://www.ease-crc.org/ont/SOMA.owl#Pouring"
    ]
  },
  "root_id": "pouring-phase-structure",
  "supersedes": null,
  "superseded_by": null,
  "provenance": {
    "generator": "openai:gpt-5.6-sol",
    "prompt_version": "generation/v5",
    "module_versions": {
      "llm_reasoner.knowledge.microworlds.flanagan.core": "1.0.0",
      "llm_reasoner.knowledge.microworlds.flanagan.object_dynamics": "1.0.0",
      "llm_reasoner.knowledge.microworlds.flanagan.prehension": "1.0.0",
      "llm_reasoner.knowledge.microworlds.flanagan.pouring": "1.0.0"
    },
    "generated_at": "2026-09-29T12:01:14.078468+00:00",
    "degraded": false,
    "exchanges": [
     